In [1]:
import numpy as np
import matplotlib.pyplot as plt
from matplotlib import animation
from scipy.signal import hilbert
from scipy.io import wavfile
from IPython.display import HTML, Audio, Video, display
from pathlib import Path

OUT = Path("../outputs/animation"); OUT.mkdir(parents=True, exist_ok=True)

In [2]:
d = np.load("./data/mf_animation_inputs.npz")
data = d["data"].astype(float)
template = d["template"].astype(float)
fs = float(d["fs"])
tail = int(round(float(d["tail_s"]) * fs))
t = float(d["t_start"]) + np.arange(len(data)) / fs            # 0 = merger
nT = len(template)
print(len(data), "data samples,", nT, "template samples, masses", d["masses"])

8192 data samples, 1228 template samples, masses [44 29]


In [3]:
USE_PYCBC_SNR = True      # True = your PyCBC result, False = the hand-written filter

tq = np.imag(hilbert(template))
rho = np.hypot(np.correlate(data, template, "valid"), np.correlate(data, tq, "valid"))
snr_hand = rho / (data[t < -1.0].std() * np.sqrt(np.sum(template ** 2)))
snr_t = t[np.arange(len(snr_hand)) + nT - tail]                # merger time at each position

snr_pyc = np.interp(snr_t, d["pyc_t"], d["pyc_snr"])           # your PyCBC curve on the same time axis
snr = snr_pyc if USE_PYCBC_SNR else snr_hand

print(f"hand-written filter peak: {snr_hand.max():.1f}")
print(f"your PyCBC peak:          {snr_pyc.max():.1f}")

hand-written filter peak: 32.7
your PyCBC peak:          19.3


In [4]:
from ipywidgets import interact, IntSlider
scale = 3 * data.std() / np.abs(template).max()

def show(i):
    fig, (ax1, ax2) = plt.subplots(2, 1, figsize=(10, 6))
    ax1.plot(t, data, color="0.5", lw=0.6)
    ax1.plot(t[i:i + nT], template * scale, color="orange", lw=2)
    ax2.plot(snr_t[:i + 1], snr[:i + 1], color="cyan")
    ax2.set_xlim(snr_t[0], snr_t[-1]); ax2.set_ylim(0, snr.max() * 1.2)
    plt.show()

interact(show, i=IntSlider(min=0, max=len(snr) - 1, step=20, value=0, continuous_update=False))

interactive(children=(IntSlider(value=0, continuous_update=False, description='i', max=6964, step=20), Output(…

<function __main__.show(i)>

In [8]:
THRESHOLD, HOLD, STEP, INTERVAL = 8, 25, 40, 40       # INTERVAL in ms, so 25 frames per second
FPS = 1000 / INTERVAL

peak_i = int(np.argmax(snr))
pos = sorted(set(range(0, len(snr), STEP)) | {peak_i})
k = pos.index(peak_i)
positions = pos[:k + 1] + [peak_i] * HOLD + pos[k + 1:]      # repeating the peak frame = a pause

fig, (ax1, ax2) = plt.subplots(2, 1, figsize=(10, 6))
fig.subplots_adjust(hspace=0.45)
ax1.plot(t, data, color="0.5", lw=0.6)
ax1.set(xlim=(t[0], t[-1]), xlabel="time relative to merger (s)", title="The template slides along the data")
tmpl_line, = ax1.plot([], [], color="orange", lw=2)

trace, = ax2.plot([], [], color="cyan")
ax2.axhline(THRESHOLD, ls="--", color="red")
ax2.set(xlim=(snr_t[0], snr_t[-1]), ylim=(0, snr.max() * 1.2),
        xlabel="time of merger in template (s)", ylabel="SNR", title="Match score")
msg = ax2.text(0.02, 0.88, "", transform=ax2.transAxes, fontsize=14, fontweight="bold")

def update(frame):
    i = positions[frame]
    tmpl_line.set_data(t[i:i + nT], template * scale)
    trace.set_data(snr_t[:i + 1], snr[:i + 1])
    best_so_far = snr[:i + 1].max()
    if best_so_far >= THRESHOLD:
        msg.set_text(f"SIGNAL FOUND!  SNR = {best_so_far:.1f}"); msg.set_color("green")
    else:
        msg.set_text(f"Searching...  best so far: {best_so_far:.1f}"); msg.set_color("black")
    return tmpl_line, trace, msg

anim = animation.FuncAnimation(fig, update, frames=len(positions), interval=INTERVAL, blit=False)
plt.close(fig)
HTML(anim.to_jshtml())

In [6]:
SR = 44100
snr_f = snr[positions]                                         # the score shown in each frame
t_a = np.arange(int(len(positions) / FPS * SR)) / SR
s_a = np.interp(t_a, np.arange(len(positions)) / FPS, snr_f)

freq = 200 + 40 * s_a                                          # pitch follows the score
tone = (0.15 + 0.55 * s_a / s_a.max()) * np.sin(2 * np.pi * np.cumsum(freq) / SR)

first = np.nonzero(snr_f >= THRESHOLD)[0]                      # bell at the first detection
if len(first):
    n0 = int(first[0] / FPS * SR)
    tb = np.arange(int(0.8 * SR)) / SR
    bell = np.exp(-4 * tb) * (np.sin(2 * np.pi * 1500 * tb) + 0.5 * np.sin(2 * np.pi * 2250 * tb))
    end = min(len(tone), n0 + len(bell))
    tone[n0:end] += 0.35 * bell[:end - n0]

audio = 0.9 * tone / np.abs(tone).max()
wavfile.write(OUT / "scan_sound.wav", SR, (audio * 32767).astype(np.int16))
display(Audio(audio, rate=SR))

In [7]:
import subprocess
silent, final = OUT / "silent.mp4", OUT / "matched_filter_with_sound.mp4"
anim.save(str(silent), writer=animation.FFMpegWriter(fps=FPS), dpi=110)
subprocess.run(["ffmpeg", "-y", "-loglevel", "error", "-i", str(silent), "-i", str(OUT / "scan_sound.wav"),
                "-c:v", "copy", "-c:a", "aac", "-shortest", str(final)], check=True)
display(Video(str(final), embed=True, width=800))